In [ ]:
#pip uninstall torch -y
#pip install torch --index-url https://download.pytorch.org/whl/cu126

In [1]:
!nvidia-smi

Sun Oct 25 21:30:23 2026       
+-----------------------------------------------------------------------------------------+
| NVIDIA-SMI 580.178.04             Driver Version: 580.178.04     CUDA Version: 13.0     |
+-----------------------------------------+------------------------+----------------------+
| GPU  Name                 Persistence-M | Bus-Id          Disp.A | Volatile Uncorr. ECC |
| Fan  Temp   Perf          Pwr:Usage/Cap |           Memory-Usage | GPU-Util  Compute M. |
|                                         |                        |               MIG M. |
|=========================================+========================+======================|
|   0  NVIDIA GeForce GTX 1080 Ti     Off |   00000000:1A:00.0 Off |                  N/A |
| 23%   21C    P8              8W /  250W |       3MiB /  11264MiB |      0%      Default |
|                                         |                        |                  N/A |
+-----------------------------------------+-----

In [2]:
import torch
import transformers

/tmp/venv_cache_igor.varejao6/lib/python3.10/site-packages/tqdm/auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm


In [6]:
import psutil

ram_gb = psutil.virtual_memory().total / 1e9
print('Your runtime has {:.1f} gigabytes of available RAM\n'.format(ram_gb))

if ram_gb < 20:
  print('Not using a high-RAM runtime')
else:
  print('You are using a high-RAM runtime!')


import sys
print(sys.version)

print("\n---\nTransformers")
import transformers
print(transformers.__version__)

print("\n---\nTorch")
import torch
print("Compiled with cuda: ", torch.cuda.is_available())
print(torch.__version__)

print("\n---\nTorchAudio")
import torchaudio
print(torchaudio.__version__)

# print("\n---\nBitsAndBytes")
# import bitsandbytes
# print(bitsandbytes.__version__)

# print(f"Compiled with CUDA: {bitsandbytes.cextension.lib.compiled_with_cuda == True}")


Your runtime has 404.3 gigabytes of available RAM

You are using a high-RAM runtime!
3.10.13 (main, Jul 23 2025, 16:24:01) [GCC 13.3.0]

---
Transformers
5.8.0

---
Torch
Compiled with cuda:  True
2.11.0+cu126

---
TorchAudio
2.11.0+cu126


In [9]:
from IPython.display import Audio


In [2]:
tensor = torch.Tensor([1, 2, 3])
tensor

tensor([1., 2., 3.])

In [3]:
tensor = tensor.to('cuda:0')
tensor.device

device(type='cuda', index=0)

In [80]:
import torch
tensor = torch.Tensor([[1, 2, 3], [3, 4, 5], [5, 6, 7], [8, 9, 10]])
print(tensor.size())

for x in tensor:
    print(x)

torch.Size([4, 3])
tensor([1., 2., 3.])
tensor([3., 4., 5.])
tensor([5., 6., 7.])
tensor([ 8.,  9., 10.])


In [4]:
!uv pip freeze --python {sys.executable} | grep torch

Using Python 3.10.13 environment at: /tmp/igor.varejao/nesenv
torch==2.11.0+cu126
torch-stoi==0.2.3
torchaudio==2.11.0+cu126
torchcodec==0.17.0
torchlibrosa==0.1.0
torchvision==0.26.0+cu126


# Testing Metrics

In [1]:
import sys
import traceback
from importlib.metadata import version

print("Python:", sys.executable)
for package in ("torch", "torchaudio", "torchcodec"):
    print(f"{package}: {version(package)}")

try:
    import torchcodec
except Exception:
    traceback.print_exc(chain=True)


Python: /tmp/igor.varejao/nesenv/bin/python
torch: 2.11.0+cu126
torchaudio: 2.11.0+cu126
torchcodec: 0.17.0+cu126


In [9]:
TEST_SAMPLE

PosixPath('/storage/datasets/igor.varejao/nes_0.8/complete/310/Cantina/310_StarWars_TheEmpireStrikesBack_06_07Cantina.wav')

In [2]:
from pathlib import Path
DATASET_DIR = Path("/storage/datasets/igor.varejao/nes_0.8/complete")
TEST_SAMPLE = DATASET_DIR / "310/Cantina/310_StarWars_TheEmpireStrikesBack_06_07Cantina.wav"

sample = torchaudio.load(TEST_SAMPLE)
sample

(tensor([[0.0921, 0.1049, 0.0478,  ..., 0.0000, 0.0000, 0.0000]]), 44100)

In [9]:

Audio(sample[0].numpy(), rate=sample[1])

### Evaluation test

In [2]:
import pandas as pd

df = pd.read_csv(DATASET_DIR / "nes_metadata.csv")

test_set = df[df.split == "test"]
test_set

NameError: name 'DATASET_DIR' is not defined

In [13]:
test_set.has_music_track_description.sum()

334

In [7]:
import os
from torch.utils.data import Dataset, DataLoader
import pandas as pd
from pathlib import Path
from typing import Literal


def collate_eval(batch : list[dict]):
    preds = torch.stack([sample["predicted"] for sample in batch])
    true = torch.stack([sample["true"] for sample in batch])
    return true, preds
    

class NESDatasetBase(Dataset):
    def __init__(self, dataset_root:str | Path, split:str | Path) -> None:
        super().__init__()

        if (isinstance(dataset_root, str)):
            dataset_root = Path(dataset_root) 
            
        self.dataset_root = dataset_root
        self.csv_path = os.path.join(self.dataset_root, "nes_metadata.csv")

        self.df = pd.read_csv(self.csv_path, dtype={"id":"object"})

        if split == "train":
            self.df:pd.DataFrame = self.df[self.df.split.isin(["train", "valid"])]
        elif split == "test":
            self.df:pd.DataFrame = self.df[self.df["split"] == "test"]
        else:
            raise ValueError("Valid split values are 'train' and 'test'")

        self.df = self.df[self.df.has_midi & self.df.has_nlm & self.df.has_music_track_description]
        self.df = self.df.reset_index()

        print(f"Initialized dataset from csv.\nHead:\n{self.df[['file_name_prefix', 'split']].head()}\nSize:{len(self)}")

    def __len__(self):
        return len(self.df)


class NESEvalDataset(NESDatasetBase):

    sample_rates = {
        "midi" : {"sample_rate": 44_100, "pred_suffix": "_midi_tokens.json"},
        "nlm"  : {"sample_rate": 44_100, "pred_suffix": "_nlm_tokens.json"},
        "audio"  : {"sample_rate": 44_100, "pred_suffix": "_generated.wav"}, # our music gen output sample rate
    }
    
    def __init__(self, dataset_root:str, predicted_root:str, domain: Literal["audio", "midi", "nlm"]) -> None:
        super().__init__(dataset_root=Path(dataset_root), split="test")
        self.domain = domain
        self.predicted_root = Path(predicted_root)
        
    def __getitem__(self, index):
        row = self.df.loc[index].to_dict()
        file_name_prefix = row["file_name_prefix"]
        
        true_sample_filepath_wav = self.dataset_root / row["file_path_wav"]
        predicted_sample_filepath_wav = self.predicted_root / self.domain / (row["file_name_prefix"] + ".mid.wav") # TODO: change for general application 

        true_sample_wav, true_sr  = torchaudio.load(true_sample_filepath_wav)
        predicted_sample_wav, predicted_sr = torchaudio.load(predicted_sample_filepath_wav)

        print(true_sample_filepath_wav)
        print(predicted_sample_filepath_wav)
        
        return {
            "true":true_sample_wav, 
            "predicted":predicted_sample_wav,
            "true_sr": true_sr,
            "predicted_sr": predicted_sr
        }

DATASET_DIR = "/storage/datasets/igor.varejao/nes_0.8/complete/"
PREDICTED_DIR = "/storage/datasets/igor.varejao/predicted/legacy/"
midi_eval_dataset = NESEvalDataset(DATASET_DIR, PREDICTED_DIR, "midi")
print(midi_eval_dataset[0])

midi_eval_loader = DataLoader(
    midi_eval_dataset,
    batch_size=1,
    num_workers=4,
    pin_memory=True,
    # collate_fn=collate_eval,
)

/tmp/ipykernel_1506101/999718673.py:24: DtypeWarning: Columns (22,32) have mixed types. Specify dtype option on import or set low_memory=False.
  self.df = pd.read_csv(self.csv_path, dtype={"id":"object"})


Initialized dataset from csv.
Head:
                                  file_name_prefix split
0            002_1943_TheBattleofMidway_00_01Title  test
1   002_1943_TheBattleofMidway_01_02PowerUpYourP38  test
2     002_1943_TheBattleofMidway_02_03MissionStart  test
3       002_1943_TheBattleofMidway_03_04AirBattleA  test
4  002_1943_TheBattleofMidway_04_05AntishipBattleA  test
Size:334
/storage/datasets/igor.varejao/nes_0.8/complete/002/Title/002_1943_TheBattleofMidway_00_01Title.wav
/storage/datasets/igor.varejao/predicted/legacy/midi/002_1943_TheBattleofMidway_00_01Title.mid.wav
{'true': tensor([[0.0000, 0.0000, 0.0000,  ..., 0.0143, 0.0143, 0.0143]]), 'predicted': tensor([[0.0000, 0.0000, 0.0000,  ..., 0.0284, 0.0284, 0.0284]]), 'true_sr': 44100, 'predicted_sr': 44100}


In [10]:
sample = midi_eval_dataset[0]
y = sample["true"][0]
sr_y = sample["true_sr"]
y_hat = sample["predicted"][0]
sr_y_hat = sample["predicted_sr"]
Audio(y, rate=sr_y)

Audio(y_hat, rate=sr_y_hat)

/storage/datasets/igor.varejao/nes_0.8/complete/002/Title/002_1943_TheBattleofMidway_00_01Title.wav
/storage/datasets/igor.varejao/predicted/legacy/midi/002_1943_TheBattleofMidway_00_01Title.mid.wav


In [ ]:
from pathlib import Path
DATASET_DIR = Path("/storage/datasets/igor.varejao/nes_0.8/complete")
TEST_SAMPLE = DATASET_DIR / "310/Cantina/310_StarWars_TheEmpireStrikesBack_06_07Cantina.wav"

sample = torchaudio.load(TEST_SAMPLE)
sample

### Testing KLD

In [29]:
%reload_ext autoreload
%autoreload 3

In [51]:
import importlib
import any2music.metrics.kld
importlib.reload(any2music.metrics.kld)
from any2music.metrics.kld import KLDMetric

kld_metric = KLDMetric()
print(kld_metric.kld_scores)

[autoreload of any2music.metrics.kld failed: Traceback (most recent call last):
  File "/tmp/igor.varejao/nesenv/lib/python3.10/site-packages/IPython/extensions/autoreload.py", line 274, in check
    superreload(m, reload, self.old_objects, self.shell)
  File "/tmp/igor.varejao/nesenv/lib/python3.10/site-packages/IPython/extensions/autoreload.py", line 500, in superreload
    update_generic(old_obj, new_obj)
  File "/tmp/igor.varejao/nesenv/lib/python3.10/site-packages/IPython/extensions/autoreload.py", line 397, in update_generic
    update(a, b)
  File "/tmp/igor.varejao/nesenv/lib/python3.10/site-packages/IPython/extensions/autoreload.py", line 365, in update_class
    update_instances(old, new)
  File "/tmp/igor.varejao/nesenv/lib/python3.10/site-packages/IPython/extensions/autoreload.py", line 323, in update_instances
    object.__setattr__(ref, "__class__", new)
TypeError: __class__ assignment only supported for mutable types or ModuleType subclasses
]
INFO:timm.models.helpers:Lo

tensor(0., device='cuda:0')


In [16]:
# convert to shape B, C, T
y_hat = y_hat.reshape([1, 1, -1])
print(y_hat.shape)
y = y.reshape([1, 1, -1])
print(y.shape)

torch.Size([1, 1, 2193166])
torch.Size([1, 1, 845341])


In [52]:
kld_metric.update(y_hat, y, sr_y_hat, sr_y)

torch.Size([1, 527])
torch.Size([1, 527])


In [53]:
kld_score = kld_metric.compute()
kld_score

{'kld': 0.08163341879844666}

In [55]:
kld_metric.reset()
kld_metric.update(y_hat, y_hat, sr_y_hat, sr_y_hat)
kld_score = kld_metric.compute()
print(kld_score)

torch.Size([1, 527])
torch.Size([1, 527])
{'kld': -0.0004991941968910396}


# Testing nesmdb api

In [39]:
from src.midi.MIDI import MIDIHandler

midi_tokenizer = "/home/igor.varejao/nes-music-gen/models/tokenizers/symbolic/midi_mmm_tokenizer.json"

handler = MIDIHandler(midi_tokenizer)
print(handler.get_nesmdb_mount_point())

[2026-10-28 12:42:53,805] MIDITokenizer [INFO] Loading tokenizer from /home/igor.varejao/nes-music-gen/models/tokenizers/symbolic/midi_mmm_tokenizer.json
[2026-10-28 12:42:53,805] MIDITokenizer [INFO] Loading tokenizer from /home/igor.varejao/nes-music-gen/models/tokenizers/symbolic/midi_mmm_tokenizer.json
[2026-10-28 12:42:53,805] MIDITokenizer [INFO] Loading tokenizer from /home/igor.varejao/nes-music-gen/models/tokenizers/symbolic/midi_mmm_tokenizer.json
[2026-10-28 12:42:53,805] MIDITokenizer [INFO] Loading tokenizer from /home/igor.varejao/nes-music-gen/models/tokenizers/symbolic/midi_mmm_tokenizer.json
[2026-10-28 12:42:53,845] MIDIHandler [INFO] API is running at http://localhost:5555
[2026-10-28 12:42:53,845] MIDIHandler [INFO] API is running at http://localhost:5555
[2026-10-28 12:42:53,845] MIDIHandler [INFO] API is running at http://localhost:5555


/storage/datasets/igor.varejao/predicted/


In [48]:
midi_path = "/storage/datasets/igor.varejao/predicted/legacy/310_StarWars_TheEmpireStrikesBack_06_07Cantina.mid"

tokens = handler.tokenize(midi_path)
ids = tokens.ids
midi_file = handler.detokenize(ids)

input_path = midi_path.replace(".mid", "_detokenized.mid")
midi_file.dump_midi(input_path)

print("MIDI file saved on", input_path)
output = handler.synthesize(input_path, os.path.dirname(input_path))
print(output)

MIDI file saved on /storage/datasets/igor.varejao/predicted/legacy/310_StarWars_TheEmpireStrikesBack_06_07Cantina_detokenized.mid


[2026-10-28 13:01:09,434] MIDIHandler [INFO] File 310_StarWars_TheEmpireStrikesBack_06_07Cantina_detokenized.mid sythesized onto file /data/legacy/310_StarWars_TheEmpireStrikesBack_06_07Cantina_detokenized.mid.wav
[2026-10-28 13:01:09,434] MIDIHandler [INFO] File 310_StarWars_TheEmpireStrikesBack_06_07Cantina_detokenized.mid sythesized onto file /data/legacy/310_StarWars_TheEmpireStrikesBack_06_07Cantina_detokenized.mid.wav
[2026-10-28 13:01:09,434] MIDIHandler [INFO] File 310_StarWars_TheEmpireStrikesBack_06_07Cantina_detokenized.mid sythesized onto file /data/legacy/310_StarWars_TheEmpireStrikesBack_06_07Cantina_detokenized.mid.wav


/data/legacy/310_StarWars_TheEmpireStrikesBack_06_07Cantina_detokenized.mid.wav


In [49]:
Audio("/storage/datasets/igor.varejao/predicted/legacy/310_StarWars_TheEmpireStrikesBack_06_07Cantina_detokenized.mid.wav")

In [47]:
Audio("/storage/datasets/igor.varejao/predicted/legacy/310_StarWars_TheEmpireStrikesBack_06_07Cantina.mid.wav")

In [46]:
midi_path = "/storage/datasets/igor.varejao/predicted/legacy/310_StarWars_TheEmpireStrikesBack_06_07Cantina.mid"

print("MIDI file sythesizing", midi_path)
output = handler.synthesize(midi_path, os.path.dirname(midi_path))
print(output)

MIDI file saved on /storage/datasets/igor.varejao/predicted/legacy/310_StarWars_TheEmpireStrikesBack_06_07Cantina_detokenized.mid


[2026-10-28 12:55:44,579] MIDIHandler [INFO] File 310_StarWars_TheEmpireStrikesBack_06_07Cantina.mid sythesized onto file /data/legacy/310_StarWars_TheEmpireStrikesBack_06_07Cantina.mid.wav
[2026-10-28 12:55:44,579] MIDIHandler [INFO] File 310_StarWars_TheEmpireStrikesBack_06_07Cantina.mid sythesized onto file /data/legacy/310_StarWars_TheEmpireStrikesBack_06_07Cantina.mid.wav
[2026-10-28 12:55:44,579] MIDIHandler [INFO] File 310_StarWars_TheEmpireStrikesBack_06_07Cantina.mid sythesized onto file /data/legacy/310_StarWars_TheEmpireStrikesBack_06_07Cantina.mid.wav


/data/legacy/310_StarWars_TheEmpireStrikesBack_06_07Cantina.mid.wav


In [ ]:
import pickle

nlm_path = "/home/igor/new/repos/nes-music-gen/dataset/complete/001/MainBGM_#_1_fast_120/001_1942_01_02MainBGM_#_1_fast_120.nlm.pkl"
tokens = handler.tokenize(nlm_path)
ids = tokens.ids
nlm_script = handler.detokenize(ids)
# nlm_commands = handler.parse_nlm(nlm_script)
# nlm_script = "\n".join([f"{cmd[0]},{cmd[1]}" for cmd in nlm_commands])
# nlm_script = "\n".join(nlm_script.splitlines()[:5] + ["w,213"])
# nlm_script = nlm_script.replace(",", "_").replace("\n", " ")


tmp_nlm_pkl = "/home/igor/new/repos/nes-music-gen/dataset/complete/test/tmp_pkl.nlm.pkl"
tmp_nlm = tmp_nlm_pkl.replace(".nlm.pkl", ".txt")
with open(tmp_nlm, "w") as f:
    f.write(nlm_script)

commands = list(map(lambda x: x.split(","), nlm_script.splitlines()))
with open(tmp_nlm_pkl, "wb") as f:
    pickle.dump(commands, f, protocol=2)


print(nlm_script)
# output = handler.synthesize("/home/igor/new/repos/nes-music-gen/dataset/complete/001/MainBGM_#_1_fast_120/001_1942_01_02MainBGM_#_1_fast_120.nlm.pkl", "/home/igor/new/repos/nes-music-gen/dataset/complete/test/")
# output = handler.synthesize("/data/001/MainBGM_#_1_fast_120/001_1942_01_02MainBGM_#_1_fast_120.nlm.pkl", "/data/test/")
# print(output)

In [35]:
help(MIDIHandler)

Help on class MIDIHandler in module src.midi.MIDI:

class MIDIHandler(builtins.object)
 |  MIDIHandler(tokenizer_path: str)
 |  
 |  Methods defined here:
 |  
 |  __init__(self, tokenizer_path: str)
 |      Initialize self.  See help(type(self)) for accurate signature.
 |  
 |  detokenize(self, numeric_ids) -> ScoreFactory()
 |  
 |  get_nesmdb_mount_point(self)
 |  
 |  synthesize(self, input_midi_path: str | pathlib.Path, output_dir: str | pathlib.Path) -> str | None
 |  
 |  tokenize(self, midi_file_path: str) -> <built-in function array>
 |  
 |  ----------------------------------------------------------------------
 |  Data descriptors defined here:
 |  
 |  __dict__
 |      dictionary for instance variables (if defined)
 |  
 |  __weakref__
 |      list of weak references to the object (if defined)

